# Textual Embeddings for StarkQA-PrimeKG using all-MiniLM-L6-v1

In this tutorial, we will perform textual (enrichment and) embeddings for StarkQA-PrimeKG and eventually construct a knowledge graph.

First of all, we need to import necessary libraries as follows:

In [1]:
# Import necessary libraries
import os
import pickle
import sys

from torch_geometric.utils import from_networkx
from tqdm import tqdm

sys.path.append("../../..")
from phronesis.synapta.datasets.primekg import PrimeKG
from phronesis.synapta.datasets.starkqa_primekg import StarkQAPrimeKG
from phronesis.synapta.utils import kg_utils
from phronesis.synapta.utils.embeddings.sentence_transformer import (
    EmbeddingWithSentenceTransformer,
)

# # Set the logging level for httpx to WARNING to suppress INFO messages
# import logging
# logging.getLogger("httpx").setLevel(logging.WARNING)

/home/awmulyadi/Repositories/office/Phronesis/venv/lib/python3.12/site-packages/tqdm/auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm
/home/awmulyadi/Repositories/office/Phronesis/venv/lib/python3.12/site-packages/pydantic/_internal/_fields.py:132: UserWarning: Field "model_id" in SysBioModel has conflict with protected namespace "model_".

You may be able to resolve this warning by setting `model_config['protected_namespaces'] = ()`.
  warnings.warn(
/home/awmulyadi/Repositories/office/Phronesis/venv/lib/python3.12/site-packages/pydantic/_internal/_fields.py:132: UserWarning: Field "model_id" in BasicoModel has conflict with protected namespace "model_".

You may be able to resolve this warning by setting `model_config['protected_namespaces'] = ()`.
  warnings.warn(
/home/awmulyadi/Repositories/office/Phronesis/venv/lib/python3.12/site-

We need to load the PrimeKG and StarkQAPrimeKG datasets in order to construct the knowledge graph for later application.

### Load PrimeKG

To load PrimeKG dataset, we can utilize the `PrimeKG` class from the phronesis/synapta library.

The `PrimeKG` needs to be initialized with the path to the PrimeKG dataset to be stored/loaded from the local directory.

In [2]:
# Define primekg data by providing a local directory where the data is stored
primekg_data = PrimeKG(local_dir="../../../../data/primekg/")

# Invoke a method to load the data
primekg_data.load_data()

# Get primekg_nodes and primekg_edges
primekg_nodes = primekg_data.get_nodes()
primekg_edges = primekg_data.get_edges()

Loading nodes of PrimeKG dataset ...
../../../../data/primekg/primekg_nodes.tsv.gz already exists. Loading the data from the local directory.
Loading edges of PrimeKG dataset ...
../../../../data/primekg/primekg_edges.tsv.gz already exists. Loading the data from the local directory.


We can check the dataframes of nodes and edges of PrimeKG as follows:

In [3]:
# Check PrimeKG nodes
primekg_nodes.head()

,node_index,node_name,node_source,node_id,node_type
0,0,PHYHIP,NCBI,9796,gene/protein
1,1,GPANK1,NCBI,7918,gene/protein
2,2,ZRSR2,NCBI,8233,gene/protein
3,3,NRF1,NCBI,4899,gene/protein
4,4,PI4KA,NCBI,5297,gene/protein


In [4]:
# Check PrimeKG edges
primekg_edges.head()

,head_index,head_name,head_source,head_id,head_type,tail_index,tail_name,tail_source,tail_id,tail_type,display_relation,relation
0,0,PHYHIP,NCBI,9796,gene/protein,8889,KIF15,NCBI,56992,gene/protein,ppi,protein_protein
1,1,GPANK1,NCBI,7918,gene/protein,2798,PNMA1,NCBI,9240,gene/protein,ppi,protein_protein
2,2,ZRSR2,NCBI,8233,gene/protein,5646,TTC33,NCBI,23548,gene/protein,ppi,protein_protein
3,3,NRF1,NCBI,4899,gene/protein,11592,MAN1B1,NCBI,11253,gene/protein,ppi,protein_protein
4,4,PI4KA,NCBI,5297,gene/protein,2122,RGS20,NCBI,8601,gene/protein,ppi,protein_protein


### Load StarkQA

In [5]:
# Define starkqa primekg data by providing a local directory where the data is stored
starkqa_data = StarkQAPrimeKG(local_dir="../../../../data/starkqa_primekg/")

# Invoke a method to load the data
starkqa_data.load_data()

# Get the StarkQAPrimeKG data, which are the QA pairs, split indices, and the node information
starkqa_df = starkqa_data.get_starkqa()
starkqa_split_indices = starkqa_data.get_starkqa_split_indicies()
starkqa_node_info = starkqa_data.get_starkqa_node_info()

Loading StarkQAPrimeKG dataset...
../../../../data/starkqa_primekg/qa/prime/stark_qa/stark_qa.csv already exists. Loading the data from the local directory.
Loading StarkQAPrimeKG embeddings...


/home/awmulyadi/Repositories/office/Phronesis/docs/notebooks/synapta/../../../phronesis/synapta/datasets/starkqa_primekg.py:141: FutureWarning: You are using `torch.load` with `weights_only=False` (the current default value), which uses the default pickle module implicitly. It is possible to construct malicious pickle data which will execute arbitrary code during unpickling (See https://github.com/pytorch/pytorch/blob/main/SECURITY.md#untrusted-models for more details). In a future release, the default value for `weights_only` will be flipped to `True`. This limits the functions that could be executed during unpickling. Arbitrary objects will no longer be allowed to be loaded via this mode unless they are explicitly allowlisted by the user via `torch.serialization.add_safe_globals`. We recommend you start setting `weights_only=True` for any use case where you don't have full control of the loaded file. Please open an issue on GitHub for any issues related to this experimental feature.


We can get a set of questions from the StarkQA dataset contained in `starkqa_df`

In [6]:
# Check StarkQA data
starkqa_df.head()

,id,query,answer_ids
0,0,Could you identify any skin diseases associate...,[95886]
1,1,What drugs target the CYP3A4 enzyme and are us...,[15450]
2,2,What is the name of the condition characterize...,"[98851, 98853]"
3,3,What drugs are used to treat epithelioid sarco...,[15698]
4,4,Can you supply a compilation of genes and prot...,"[7161, 22045]"


Within the `starkqa_node_info` dictionary, we can access additional information of the nodes in the PrimeKG dataset provided by StarkQA team.

In [7]:
# We can obtain additional node information from StarkQAPrimeKG
starkqa_node_info[0]

{'id': 9796,
 'type': 'gene/protein',
 'name': 'PHYHIP',
 'source': 'NCBI',
 'details': {'query': 'PHYHIP',
  '_id': '9796',
  '_score': 17.934021,
  'alias': ['DYRK1AP3', 'PAHX-AP', 'PAHXAP1'],
  'genomic_pos': {'chr': '8',
   'end': 22232101,
   'ensemblgene': 'ENSG00000168490',
   'start': 22219703,
   'strand': -1},
  'name': 'phytanoyl-CoA 2-hydroxylase interacting protein',
  'summary': 'Enables protein tyrosine kinase binding activity. Involved in protein localization. Located in cytoplasm. [provided by Alliance of Genome Resources, Apr 2022]'}}

### Textual Enrichment over PrimeKG

We begin with the textual enrichment over the PrimeKG nodes by using the StarkQA node information.

Note that not all nodes in the PrimeKG have additional information. For this case, we provide a basic text enrichment for the nodes by simply specifying their node name and type.

In [8]:
def enrich_node(data, node_info):
    """
    Enrich the node with additional information from StarkQA-PrimeKG

    Args:
        data (dict): The node data from PrimeKG
        node_info (dict): The node information from StarkQA-PrimeKG
    """
    # Basic textual enrichment of the node
    enriched_node = f"{data['node_name']} belongs to {data['node_type']} category. "
    # Only enrich the node if the node type is gene/protein, drug, disease, or pathway, which
    # has additional information in the node_info of StarkQA-PrimeKG
    added_info = ""
    if data["node_type"] == "gene/protein":
        added_info = (
            node_info["details"]["summary"] if "summary" in node_info["details"] else ""
        )
    elif data["node_type"] == "drug":
        added_info = " ".join(
            [
                str(node_info["details"]["description"]).replace("nan", ""),
                str(node_info["details"]["mechanism_of_action"]).replace("nan", ""),
                str(node_info["details"]["protein_binding"]).replace("nan", ""),
                str(node_info["details"]["pharmacodynamics"]).replace("nan", ""),
                str(node_info["details"]["indication"]).replace("nan", ""),
            ]
        )
    elif data["node_type"] == "disease":
        added_info = " ".join(
            [
                str(node_info["details"]["mondo_definition"]).replace("nan", ""),
                str(node_info["details"]["mayo_symptoms"]).replace("nan", ""),
                str(node_info["details"]["mayo_causes"]).replace("nan", ""),
            ]
        )
    elif data["node_type"] == "pathway":
        added_info += (
            f"This pathway found in {node_info['details']['speciesName']}. "
            + " ".join([x["text"] for x in node_info["details"]["summation"]])
            if "details" in node_info
            else ""
        )
    # Append the additional information for enrichment
    enriched_node += added_info
    return enriched_node

By using the above function, we can enrich the node information from PrimeKG with additional information from StarkQA-PrimeKG as shown below:

In [9]:
# Perform node enrichment for each row in primekg_nodes
enriched_nodes = primekg_nodes.apply(
    lambda x: enrich_node(x, starkqa_node_info[x["node_index"]]), axis=1
).tolist()
primekg_nodes["enriched_node"] = enriched_nodes
primekg_nodes.head()

,node_index,node_name,node_source,node_id,node_type,enriched_node
0,0,PHYHIP,NCBI,9796,gene/protein,PHYHIP belongs to gene/protein category. Enabl...
1,1,GPANK1,NCBI,7918,gene/protein,GPANK1 belongs to gene/protein category. This ...
2,2,ZRSR2,NCBI,8233,gene/protein,ZRSR2 belongs to gene/protein category. This g...
3,3,NRF1,NCBI,4899,gene/protein,NRF1 belongs to gene/protein category. This ge...
4,4,PI4KA,NCBI,5297,gene/protein,PI4KA belongs to gene/protein category. This g...


Subsequently, we can perform similar textual enrichment for the edges in PrimeKG.

Since StarkQA only provides node information, we can only enrich the edges with basic information of the triples in combination with the head and tail nodes.

In [10]:
# Perform textual enrichment over the edges by simply concatenating the head and tail nodes with the relation followed by the enriched node information
enriched_edges = primekg_edges.apply(
    lambda x: f"{x['head_name']} ({x['head_type']}) has a direct relationship of {x['display_relation']} with {x['tail_name']} ({x['tail_type']}).",
    axis=1,
).tolist()
enriched_edges

['PHYHIP (gene/protein) has a direct relationship of ppi with KIF15 (gene/protein).',
 'GPANK1 (gene/protein) has a direct relationship of ppi with PNMA1 (gene/protein).',
 'ZRSR2 (gene/protein) has a direct relationship of ppi with TTC33 (gene/protein).',
 'NRF1 (gene/protein) has a direct relationship of ppi with MAN1B1 (gene/protein).',
 'PI4KA (gene/protein) has a direct relationship of ppi with RGS20 (gene/protein).',
 'SLC15A1 (gene/protein) has a direct relationship of ppi with RTL8C (gene/protein).',
 'EIF3I (gene/protein) has a direct relationship of ppi with PAXIP1 (gene/protein).',
 'FAXDC2 (gene/protein) has a direct relationship of ppi with SLC10A6 (gene/protein).',
 'MT1A (gene/protein) has a direct relationship of ppi with TP53 (gene/protein).',
 'SORT1 (gene/protein) has a direct relationship of ppi with PALMD (gene/protein).',
 'LRP5 (gene/protein) has a direct relationship of ppi with FOXP3 (gene/protein).',
 'RPS8 (gene/protein) has a direct relationship of ppi with 

In [11]:
# # For more detailed information, we can include head and tail node information in the enriched edge
# enriched_heads = primekg_edges.join(primekg_nodes.set_index('node_index'), on='head_index')[['enriched_node']].values.flatten().tolist()
# enriched_tails = primekg_edges.join(primekg_nodes.set_index('node_index'), on='tail_index')[['enriched_node']].values.flatten().tolist()

# # Concatenate the enriched head and tail nodes with the enriched edge
# mini_batch_size = 10000
# enriched_edges_final = []
# for i in tqdm(range(0, len(enriched_edges), mini_batch_size)):
#     outputs = [f"{head} {edge} {tail}" for head, edge, tail in zip(enriched_heads[i:i+mini_batch_size], enriched_edges[i:i+mini_batch_size], enriched_tails[i:i+mini_batch_size])]
#     enriched_edges_final.extend(outputs)
# enriched_edges_final

In [12]:
# Check the enriched edges
# primekg_edges['enriched_edge'] = enriched_edges_final
primekg_edges["enriched_edge"] = enriched_edges
primekg_edges.head()

,head_index,head_name,head_source,head_id,head_type,tail_index,tail_name,tail_source,tail_id,tail_type,display_relation,relation,enriched_edge
0,0,PHYHIP,NCBI,9796,gene/protein,8889,KIF15,NCBI,56992,gene/protein,ppi,protein_protein,PHYHIP (gene/protein) has a direct relationshi...
1,1,GPANK1,NCBI,7918,gene/protein,2798,PNMA1,NCBI,9240,gene/protein,ppi,protein_protein,GPANK1 (gene/protein) has a direct relationshi...
2,2,ZRSR2,NCBI,8233,gene/protein,5646,TTC33,NCBI,23548,gene/protein,ppi,protein_protein,ZRSR2 (gene/protein) has a direct relationship...
3,3,NRF1,NCBI,4899,gene/protein,11592,MAN1B1,NCBI,11253,gene/protein,ppi,protein_protein,NRF1 (gene/protein) has a direct relationship ...
4,4,PI4KA,NCBI,5297,gene/protein,2122,RGS20,NCBI,8601,gene/protein,ppi,protein_protein,PI4KA (gene/protein) has a direct relationship...


### Textual Embedding over PrimeKG

We can perform embedding using the enriched nodes and edges using `EmbeddingWithSentenceTransformer` class.

Here we will use `sentence-transformers/all-MiniLM-L6-v1` provided by HuggingFace via `sentence_transformer` library to embed the enriched nodes and edges.

For more detailed information on this embedding model, please refer to the documentation:
- https://huggingface.co/sentence-transformers/all-MiniLM-L6-v1


In [13]:
# Using nomic-ai/nomic-embed-text-v1.5 model with half precision for faster embedding
emb_model = EmbeddingWithSentenceTransformer(
    model_name="sentence-transformers/all-MiniLM-L6-v1",
    model_cache_dir="../../../../data/sentence-transformers/all-MiniLM-L6-v1",
    trust_remote_code=True,
)

INFO:sentence_transformers.SentenceTransformer:Use pytorch device_name: cuda
INFO:sentence_transformers.SentenceTransformer:Load pretrained SentenceTransformer: sentence-transformers/all-MiniLM-L6-v1


#### Query Embedding

Load the pre-processed embeddings, if available.

In [8]:
# # # Load the enriched nodes dataframe from parquet file
# starkqa_df = pd.read_parquet(os.path.join(starkqa_data.local_dir, 'starkqaprimekg_queries_embedded.parquet'), engine='pyarrow')

# # Check the dataframe of query embeddings
# starkqa_df.head()

,id,query,answer_ids,query_embedded
0,0,Could you identify any skin diseases associate...,[95886],"[0.050286733, 0.0050845086, 0.06326583, 0.0360..."
1,1,What drugs target the CYP3A4 enzyme and are us...,[15450],"[0.009708624, 0.01434415, -0.07435164, -0.0736..."
2,2,What is the name of the condition characterize...,"[98851, 98853]","[-0.058651656, -0.0031773308, 0.015822958, -0...."
3,3,What drugs are used to treat epithelioid sarco...,[15698],"[-0.035772394, 0.064148985, -0.018727051, -0.0..."
4,4,Can you supply a compilation of genes and prot...,"[7161, 22045]","[-0.072102964, -0.008873461, -0.007186646, 0.0..."


If there is no pre-processed query embeddings, run the following codes to generate embeddings.

Otherwise, skip the following cells and go to `Node Embedding`.

In [15]:
# Prepend prefix to the query
starkqa_df["query_prefixed"] = starkqa_df["query"].apply(lambda x: f"search_query: {x}")
starkqa_df.head()

,id,query,answer_ids,query_prefixed
0,0,Could you identify any skin diseases associate...,[95886],search_query: Could you identify any skin dise...
1,1,What drugs target the CYP3A4 enzyme and are us...,[15450],search_query: What drugs target the CYP3A4 enz...
2,2,What is the name of the condition characterize...,"[98851, 98853]",search_query: What is the name of the conditio...
3,3,What drugs are used to treat epithelioid sarco...,[15698],search_query: What drugs are used to treat epi...
4,4,Can you supply a compilation of genes and prot...,"[7161, 22045]",search_query: Can you supply a compilation of ...


In [16]:
# Since the records of queries has large amount of data, we will split them into mini-batches
mini_batch_size = 1000
query_embeddings = []
for i in tqdm(range(0, starkqa_df.shape[0], mini_batch_size)):
    outputs = emb_model.embed_documents(
        starkqa_df.query_prefixed.values.tolist()[i : i + mini_batch_size]
    )
    query_embeddings.extend(outputs)
query_embeddings

100%|██████████| 12/12 [00:02<00:00,  4.74it/s]


[array([ 5.02867326e-02,  5.08450856e-03,  6.32658303e-02,  3.60353254e-02,
        -2.66331155e-02,  7.72449281e-03,  3.32401060e-02, -2.61908788e-02,
        -6.12661876e-02,  3.15996222e-02, -2.64444901e-03, -3.24310809e-02,
        -1.39322560e-02,  2.99506988e-02, -2.44957190e-02, -1.00047430e-02,
        -6.24146834e-02,  4.36206274e-02,  9.67865288e-02,  3.82688567e-02,
        -7.65352845e-02, -2.88652796e-02,  6.41495630e-04, -1.54881570e-02,
        -2.33018156e-02, -7.30378032e-02,  1.06982775e-01, -2.73176525e-02,
        -8.09853300e-02,  3.31253186e-02, -7.91885555e-02, -1.08804069e-02,
        -8.70838314e-02,  4.27552313e-03,  8.35634675e-03, -5.16396351e-02,
        -8.04500189e-03,  4.74858731e-02, -1.90007277e-02,  4.21623476e-02,
        -5.79571836e-02, -3.81665826e-02, -2.38694008e-02,  2.82901339e-02,
         3.73054622e-03, -1.81201696e-02, -2.72811670e-02,  2.01351140e-02,
         8.87860823e-03, -2.60056183e-02,  6.58426136e-02, -1.01149574e-01,
         3.3

In [17]:
# Check the shape of the query embeddings
len(query_embeddings), len(query_embeddings[0])

(11204, 384)

In [18]:
# Add them as features to the dataframe
starkqa_df["query_embedded"] = query_embeddings

# Drop and rename several columns
starkqa_df.drop(columns=["query_prefixed"], inplace=True)

# Check dataframe of nodes
starkqa_df.head()

,id,query,answer_ids,query_embedded
0,0,Could you identify any skin diseases associate...,[95886],"[0.050286733, 0.0050845086, 0.06326583, 0.0360..."
1,1,What drugs target the CYP3A4 enzyme and are us...,[15450],"[0.009708624, 0.01434415, -0.07435164, -0.0736..."
2,2,What is the name of the condition characterize...,"[98851, 98853]","[-0.058651656, -0.0031773308, 0.015822958, -0...."
3,3,What drugs are used to treat epithelioid sarco...,[15698],"[-0.035772394, 0.064148985, -0.018727051, -0.0..."
4,4,Can you supply a compilation of genes and prot...,"[7161, 22045]","[-0.072102964, -0.008873461, -0.007186646, 0.0..."


In [19]:
# Save the embedded queries dataframes to parquet file
starkqa_df.to_parquet(
    os.path.join(starkqa_data.local_dir, "starkqaprimekg_queries_embedded.parquet"),
    compression="gzip",
    index=False,
)

#### Node Embedding

Load the pre-processed embeddings, if available.

In [9]:
# # # Load the enriched nodes dataframe from parquet file
# primekg_nodes = pd.read_parquet(os.path.join(starkqa_data.local_dir, 'starkqaprimekg_nodes_embedded.parquet'), engine='pyarrow')

# # Check the dataframe of nodes, need to re-index the dataframe
# # Duplicate a node_name as index and use it as index
# primekg_nodes['node'] = primekg_nodes['node_id']
# primekg_nodes.set_index('node', inplace=True)
# primekg_nodes.head()

,node_id,node_name,node_type,enriched_node,x
node,,,,,
0,0,PHYHIP,gene/protein,PHYHIP belongs to gene/protein category. Enabl...,"[-0.06876933, 0.00096770556, -0.0630331, -0.04..."
1,1,GPANK1,gene/protein,GPANK1 belongs to gene/protein category. This ...,"[-0.08932163, 0.031602174, -0.102335155, -0.03..."
2,2,ZRSR2,gene/protein,ZRSR2 belongs to gene/protein category. This g...,"[-0.10059608, -0.020288778, 0.008750704, 0.003..."
3,3,NRF1,gene/protein,NRF1 belongs to gene/protein category. This ge...,"[-0.09837414, -0.02768978, -0.061966445, 0.026..."
4,4,PI4KA,gene/protein,PI4KA belongs to gene/protein category. This g...,"[-0.03965294, -0.0017360917, -0.12756099, -5.2..."


If there is no pre-processed node embeddings, run the following codes to generate embeddings.

Otherwise, skip the following cells and go to `Edge Embedding`.

In [21]:
# Prepend prefix to the enriched node
primekg_nodes["enriched_node_prefixed"] = primekg_nodes["enriched_node"].apply(
    lambda x: f"search_document: {x}"
)
primekg_nodes.head()

,node_index,node_name,node_source,node_id,node_type,enriched_node,enriched_node_prefixed
0,0,PHYHIP,NCBI,9796,gene/protein,PHYHIP belongs to gene/protein category. Enabl...,search_document: PHYHIP belongs to gene/protei...
1,1,GPANK1,NCBI,7918,gene/protein,GPANK1 belongs to gene/protein category. This ...,search_document: GPANK1 belongs to gene/protei...
2,2,ZRSR2,NCBI,8233,gene/protein,ZRSR2 belongs to gene/protein category. This g...,search_document: ZRSR2 belongs to gene/protein...
3,3,NRF1,NCBI,4899,gene/protein,NRF1 belongs to gene/protein category. This ge...,search_document: NRF1 belongs to gene/protein ...
4,4,PI4KA,NCBI,5297,gene/protein,PI4KA belongs to gene/protein category. This g...,search_document: PI4KA belongs to gene/protein...


In [22]:
# Since the records of nodes has large amount of data, we will split them into mini-batches
mini_batch_size = 1000
node_embeddings = []
for i in tqdm(range(0, primekg_nodes.shape[0], mini_batch_size)):
    outputs = emb_model.embed_documents(
        primekg_nodes.enriched_node_prefixed.values.tolist()[i : i + mini_batch_size]
    )
    node_embeddings.extend(outputs)
node_embeddings

100%|██████████| 130/130 [00:27<00:00,  4.68it/s]


[array([-6.87693283e-02,  9.67705564e-04, -6.30330965e-02, -4.65085246e-02,
         3.50460298e-02,  3.16849463e-02, -6.78631738e-02,  4.28547412e-02,
         8.91752988e-02,  1.22461151e-02,  9.30449739e-02,  3.68912704e-02,
        -6.56770915e-02,  3.57450619e-02, -1.91227738e-02, -1.56569798e-02,
        -4.84757125e-02,  6.87765926e-02, -6.00229343e-03, -7.96875954e-02,
         3.36735286e-02,  4.09734994e-02,  8.31681192e-02,  1.95677802e-02,
        -9.90630910e-02, -9.36042890e-02,  2.89827981e-03,  3.48431319e-02,
        -3.42018902e-02, -2.03435961e-02, -3.71870026e-02,  4.83692624e-02,
        -1.97366737e-02,  1.28893936e-02,  2.67398637e-02,  1.04938947e-01,
        -3.63062695e-02, -9.61233079e-02,  1.12238780e-01, -7.65134171e-02,
         6.11469224e-02,  7.51252659e-03,  5.72748631e-02, -2.16394141e-02,
        -8.24562684e-02,  8.16211328e-02,  1.24747306e-02,  2.03059781e-02,
         2.29022931e-02, -4.35879156e-02, -6.19880669e-02, -5.48641644e-02,
        -1.2

In [23]:
# Check the shape of the node embeddings
len(node_embeddings), len(node_embeddings[0])

(129375, 384)

In [24]:
# Add them as features to the dataframe
primekg_nodes["x"] = node_embeddings

# Drop and rename several columns
primekg_nodes.drop(
    columns=["node_source", "node_id", "enriched_node_prefixed"], inplace=True
)
primekg_nodes.rename(columns={"node_index": "node_id"}, inplace=True)

# Check dataframe of nodes
primekg_nodes.head()

,node_id,node_name,node_type,enriched_node,x
0,0,PHYHIP,gene/protein,PHYHIP belongs to gene/protein category. Enabl...,"[-0.06876933, 0.00096770556, -0.0630331, -0.04..."
1,1,GPANK1,gene/protein,GPANK1 belongs to gene/protein category. This ...,"[-0.08932163, 0.031602174, -0.102335155, -0.03..."
2,2,ZRSR2,gene/protein,ZRSR2 belongs to gene/protein category. This g...,"[-0.10059608, -0.020288778, 0.008750704, 0.003..."
3,3,NRF1,gene/protein,NRF1 belongs to gene/protein category. This ge...,"[-0.09837414, -0.02768978, -0.061966445, 0.026..."
4,4,PI4KA,gene/protein,PI4KA belongs to gene/protein category. This g...,"[-0.03965294, -0.0017360917, -0.12756099, -5.2..."


In [25]:
# Duplicate a node_name as index and use it as index
primekg_nodes["node"] = primekg_nodes["node_id"]
primekg_nodes.set_index("node", inplace=True)
primekg_nodes.head()

,node_id,node_name,node_type,enriched_node,x
node,,,,,
0,0,PHYHIP,gene/protein,PHYHIP belongs to gene/protein category. Enabl...,"[-0.06876933, 0.00096770556, -0.0630331, -0.04..."
1,1,GPANK1,gene/protein,GPANK1 belongs to gene/protein category. This ...,"[-0.08932163, 0.031602174, -0.102335155, -0.03..."
2,2,ZRSR2,gene/protein,ZRSR2 belongs to gene/protein category. This g...,"[-0.10059608, -0.020288778, 0.008750704, 0.003..."
3,3,NRF1,gene/protein,NRF1 belongs to gene/protein category. This ge...,"[-0.09837414, -0.02768978, -0.061966445, 0.026..."
4,4,PI4KA,gene/protein,PI4KA belongs to gene/protein category. This g...,"[-0.03965294, -0.0017360917, -0.12756099, -5.2..."


In [26]:
# Save the embedded nodes dataframes to parquet file
primekg_nodes.to_parquet(
    os.path.join(starkqa_data.local_dir, "starkqaprimekg_nodes_embedded.parquet"),
    compression="gzip",
    index=False,
)

#### Edge Embedding

Load the pre-processed embeddings, if available.

In [10]:
# # Load the enriched edges dataframes from parquet file
# primekg_edges = pd.read_parquet(os.path.join(starkqa_data.local_dir, 'starkqaprimekg_edges_embedded.parquet'), engine='pyarrow')

# # Check the dataframe of edges
# primekg_edges.head()

,head_id,head_name,tail_id,tail_name,edge_type,enriched_edge,edge_attr
0,0,PHYHIP,8889,KIF15,ppi,PHYHIP (gene/protein) has a direct relationshi...,"[-0.13521017, -0.045208305, -0.03294481, -0.08..."
1,1,GPANK1,2798,PNMA1,ppi,GPANK1 (gene/protein) has a direct relationshi...,"[-0.1397728, -0.0042078006, -0.059832085, -0.0..."
2,2,ZRSR2,5646,TTC33,ppi,ZRSR2 (gene/protein) has a direct relationship...,"[-0.13457243, -0.008945061, -0.030644426, -0.0..."
3,3,NRF1,11592,MAN1B1,ppi,NRF1 (gene/protein) has a direct relationship ...,"[-0.09951454, -0.068410024, -0.06257362, -0.00..."
4,4,PI4KA,2122,RGS20,ppi,PI4KA (gene/protein) has a direct relationship...,"[-0.051837396, -0.023969728, -0.10354268, 0.00..."


If there is no pre-processed node embeddings, run the following codes to generate embeddings.

Otherwise, skip the following cells.

In [28]:
# Prepend prefix to the enriched edge
primekg_edges["enriched_edge_prefixed"] = primekg_edges["enriched_edge"].apply(
    lambda x: f"search_document: {x}"
)
primekg_edges.head()

,head_index,head_name,head_source,head_id,head_type,tail_index,tail_name,tail_source,tail_id,tail_type,display_relation,relation,enriched_edge,enriched_edge_prefixed
0,0,PHYHIP,NCBI,9796,gene/protein,8889,KIF15,NCBI,56992,gene/protein,ppi,protein_protein,PHYHIP (gene/protein) has a direct relationshi...,search_document: PHYHIP (gene/protein) has a d...
1,1,GPANK1,NCBI,7918,gene/protein,2798,PNMA1,NCBI,9240,gene/protein,ppi,protein_protein,GPANK1 (gene/protein) has a direct relationshi...,search_document: GPANK1 (gene/protein) has a d...
2,2,ZRSR2,NCBI,8233,gene/protein,5646,TTC33,NCBI,23548,gene/protein,ppi,protein_protein,ZRSR2 (gene/protein) has a direct relationship...,search_document: ZRSR2 (gene/protein) has a di...
3,3,NRF1,NCBI,4899,gene/protein,11592,MAN1B1,NCBI,11253,gene/protein,ppi,protein_protein,NRF1 (gene/protein) has a direct relationship ...,search_document: NRF1 (gene/protein) has a dir...
4,4,PI4KA,NCBI,5297,gene/protein,2122,RGS20,NCBI,8601,gene/protein,ppi,protein_protein,PI4KA (gene/protein) has a direct relationship...,search_document: PI4KA (gene/protein) has a di...


In [29]:
# Since the records of edges has large amount of data, we will split them into mini-batches
mini_batch_size = 1000
edge_embeddings = []
for i in tqdm(range(0, primekg_edges.shape[0], mini_batch_size)):
    outputs = emb_model.embed_documents(
        primekg_edges.enriched_edge_prefixed.values.tolist()[i : i + mini_batch_size]
    )
    edge_embeddings.extend(outputs)
edge_embeddings

100%|██████████| 8101/8101 [47:54<00:00,  2.82it/s]


[array([-1.35210171e-01, -4.52083051e-02, -3.29448096e-02, -8.41252357e-02,
         9.49123502e-03,  6.04386395e-03, -7.10042790e-02,  7.82562140e-03,
         4.44377549e-02,  4.82885204e-02,  1.36771560e-01, -1.80205461e-02,
        -1.25193503e-02,  7.01050982e-02, -5.56586264e-03, -6.85594529e-02,
        -5.96926510e-02,  2.45100074e-02, -5.41764610e-02, -7.08201230e-02,
         3.23662497e-02,  2.50925384e-02,  5.35172150e-02,  2.42691170e-02,
        -6.27015680e-02,  2.80299895e-02,  2.14998592e-02, -2.44950559e-02,
        -8.83326773e-03, -3.08159762e-03,  4.67813909e-02,  7.80780539e-02,
         1.56074818e-02, -1.13355247e-02,  5.49938567e-02,  4.81757186e-02,
        -5.80129102e-02, -9.84720215e-02,  9.14814025e-02, -2.19850186e-02,
         6.65768087e-02, -1.03994757e-02,  7.79459178e-02,  1.69948284e-02,
         6.78214431e-03,  1.27032688e-02, -2.04296652e-02,  3.71666327e-02,
         1.67176351e-02, -2.43207254e-03, -6.03913330e-02, -1.79235898e-02,
        -5.5

In [30]:
# Check the shape of the edge embeddings
len(edge_embeddings), len(edge_embeddings[0])

(8100498, 384)

In [31]:
# Add them as features to the dataframe
primekg_edges["edge_attr"] = edge_embeddings

# Drop and rename several columns
primekg_edges.drop(
    columns=[
        "head_source",
        "head_id",
        "head_type",
        "tail_source",
        "tail_id",
        "tail_type",
        "relation",
        "enriched_edge_prefixed",
    ],
    inplace=True,
)
primekg_edges.rename(
    columns={
        "head_index": "head_id",
        "tail_index": "tail_id",
        "display_relation": "edge_type",
    },
    inplace=True,
)

# Check dataframe of edges
primekg_edges.head()

,head_id,head_name,tail_id,tail_name,edge_type,enriched_edge,edge_attr
0,0,PHYHIP,8889,KIF15,ppi,PHYHIP (gene/protein) has a direct relationshi...,"[-0.13521017, -0.045208305, -0.03294481, -0.08..."
1,1,GPANK1,2798,PNMA1,ppi,GPANK1 (gene/protein) has a direct relationshi...,"[-0.1397728, -0.0042078006, -0.059832085, -0.0..."
2,2,ZRSR2,5646,TTC33,ppi,ZRSR2 (gene/protein) has a direct relationship...,"[-0.13457243, -0.008945061, -0.030644426, -0.0..."
3,3,NRF1,11592,MAN1B1,ppi,NRF1 (gene/protein) has a direct relationship ...,"[-0.09951454, -0.068410024, -0.06257362, -0.00..."
4,4,PI4KA,2122,RGS20,ppi,PI4KA (gene/protein) has a direct relationship...,"[-0.051837396, -0.023969728, -0.10354268, 0.00..."


In [32]:
# Save the embedded edges dataframes to parquet file
primekg_edges.to_parquet(
    os.path.join(starkqa_data.local_dir, "starkqaprimekg_edges_embedded.parquet"),
    compression="gzip",
    index=False,
)

### Knowledge Graph Construction

We would like to convert our dataframes to networkx `DiGraph` object.

In [11]:
# Convert dataframes to knowledge graph as networkx object
kg = kg_utils.df_pandas_to_kg(
    primekg_edges, primekg_nodes, node_source="head_id", node_target="tail_id"
)

In [12]:
# Save graph object
with open(os.path.join(starkqa_data.local_dir, "kg_nx_graph.pkl"), "wb") as f:
    pickle.dump(kg, f)

# # Load graph object
# with open(os.path.join(starkqa_data.local_dir, 'kg_nx_graph.pkl'), 'rb') as f:
#     kg = pickle.load(f)

In [13]:
print("#Nodes", kg.number_of_nodes())
print("#Edges", kg.number_of_edges())

#Nodes 129375
#Edges 8099284


We can convert the networkx graph to PyG `Data` object

In [14]:
# Convert networkx graph to PyG data object
pyg_graph = from_networkx(kg)

# Save graph object
with open(os.path.join(starkqa_data.local_dir, "kg_pyg_graph.pkl"), "wb") as f:
    pickle.dump(pyg_graph, f)

# Load graph object
# with open(os.path.join(starkqa_data.local_dir, 'kg_pyg_graph.pkl'), 'rb') as f:
#     pyg_graph = pickle.load(f)

/home/awmulyadi/Repositories/office/Phronesis/venv/lib/python3.12/site-packages/torch_geometric/utils/convert.py:278: UserWarning: Creating a tensor from a list of numpy.ndarrays is extremely slow. Please consider converting the list to a single numpy.ndarray with numpy.array() before converting to a tensor. (Triggered internally at ../torch/csrc/utils/tensor_new.cpp:278.)
  data_dict[key] = torch.as_tensor(value)


Lastly, we will also prepare a textualized graph of nodes and edges for RAG application, for instance.


In [15]:
# Prepare nodes
nodes_df = primekg_nodes.copy()
nodes_df.reset_index(drop=True, inplace=True)
nodes_df.drop(columns=["node_type", "x"], inplace=True)
nodes_df.rename(columns={"enriched_node": "node_attr"}, inplace=True)
nodes_df.head()

,node_id,node_name,node_attr
0,0,PHYHIP,PHYHIP belongs to gene/protein category. Enabl...
1,1,GPANK1,GPANK1 belongs to gene/protein category. This ...
2,2,ZRSR2,ZRSR2 belongs to gene/protein category. This g...
3,3,NRF1,NRF1 belongs to gene/protein category. This ge...
4,4,PI4KA,PI4KA belongs to gene/protein category. This g...


In [16]:
# Save it to parquet file
nodes_df.to_parquet(
    os.path.join(starkqa_data.local_dir, "kg_textualized_graph_nodes.parquet"),
    compression="gzip",
    index=False,
)

In [17]:
# Prepare edges
edges_df = primekg_edges.copy()
edges_df.drop(columns=["enriched_edge", "edge_attr"], inplace=True)
edges_df.head()

,head_id,head_name,tail_id,tail_name,edge_type
0,0,PHYHIP,8889,KIF15,ppi
1,1,GPANK1,2798,PNMA1,ppi
2,2,ZRSR2,5646,TTC33,ppi
3,3,NRF1,11592,MAN1B1,ppi
4,4,PI4KA,2122,RGS20,ppi


In [18]:
# Save it to parquet file
edges_df.to_parquet(
    os.path.join(starkqa_data.local_dir, "kg_textualized_graph_edges.parquet"),
    compression="gzip",
    index=False,
)